In [1]:
import pandas as pd
from sklearn.model_selection import train_test_split

TRAIN_SZ = 0.8
VALID_SZ = 1.0 - TRAIN_SZ

# Read the data
train = pd.read_csv('../datasets/home-data-for-ml-course/train.csv', index_col='Id')
test = pd.read_csv('../datasets/home-data-for-ml-course/test.csv', index_col='Id')

# Remove rows with missing target, separate target from predictors
train.dropna(axis=0, subset=['SalePrice'], inplace=True)
y = train.SalePrice              
X = train.drop(['SalePrice'], axis=1)

# Break off validation set from training data
X_train, X_valid, y_train, y_valid = train_test_split(X, y, 
                                                      train_size=TRAIN_SZ, test_size=VALID_SZ,
                                                      random_state=0)


# Select categorical columns with relatively low cardinality (convenient but arbitrary)
N = 10
low_cardinality_cols = [col for col in X_train.columns 
                        if X_train[col].dtype == "object" 
                        and X_train[col].nunique() < N]

# Select numeric columns
numeric_cols = [col for col in X_train.columns 
                if X_train[col].dtype in ['int64', 'float64']]

# Keep selected columns only
predictor_cols = low_cardinality_cols + numeric_cols
X_train = X_train[predictor_cols]
X_valid = X_valid[predictor_cols]
X_test = test[predictor_cols].copy()

# One-hot encode the data (to shorten the code, we use pandas)
X_train = pd.get_dummies(X_train)
X_valid = pd.get_dummies(X_valid)
X_test = pd.get_dummies(X_test)
X_train, X_valid = X_train.align(X_valid, join='left', axis=1)
X_train, X_test = X_train.align(X_test, join='left', axis=1)

In [2]:
X_train.head()

,MSSubClass,LotFrontage,LotArea,OverallQual,OverallCond,YearBuilt,YearRemodAdd,MasVnrArea,BsmtFinSF1,BsmtFinSF2,...,SaleType_ConLw,SaleType_New,SaleType_Oth,SaleType_WD,SaleCondition_Abnorml,SaleCondition_AdjLand,SaleCondition_Alloca,SaleCondition_Family,SaleCondition_Normal,SaleCondition_Partial
Id,,,,,,,,,,,,,,,,,,,,,
619,20,90.0,11694,9,5,2007,2007,452.0,48,0,...,False,True,False,False,False,False,False,False,False,True
871,20,60.0,6600,5,5,1962,1962,0.0,0,0,...,False,False,False,True,False,False,False,False,True,False
93,30,80.0,13360,5,7,1921,2006,0.0,713,0,...,False,False,False,True,False,False,False,False,True,False
818,20,NaN,13265,8,5,2002,2002,148.0,1218,0,...,False,False,False,True,False,False,False,False,True,False
303,20,118.0,13704,7,5,2001,2002,150.0,0,0,...,False,False,False,True,False,False,False,False,True,False


In [3]:
X_valid.head()

,MSSubClass,LotFrontage,LotArea,OverallQual,OverallCond,YearBuilt,YearRemodAdd,MasVnrArea,BsmtFinSF1,BsmtFinSF2,...,SaleType_ConLw,SaleType_New,SaleType_Oth,SaleType_WD,SaleCondition_Abnorml,SaleCondition_AdjLand,SaleCondition_Alloca,SaleCondition_Family,SaleCondition_Normal,SaleCondition_Partial
Id,,,,,,,,,,,,,,,,,,,,,
530,20,NaN,32668,6,3,1957,1975,NaN,1219,0,...,NaN,False,False,True,False,False,True,False,False,False
492,50,79.0,9490,6,7,1941,1950,0.0,403,165,...,NaN,False,False,True,False,False,False,False,True,False
460,50,NaN,7015,5,4,1950,1950,161.0,185,0,...,NaN,False,False,True,False,False,False,False,True,False
280,60,83.0,10005,7,5,1977,1977,299.0,392,0,...,NaN,False,False,True,False,False,False,False,True,False
656,160,21.0,1680,6,5,1971,1971,381.0,0,0,...,NaN,False,False,True,False,False,False,True,False,False


In [4]:
X_test.head()

,MSSubClass,LotFrontage,LotArea,OverallQual,OverallCond,YearBuilt,YearRemodAdd,MasVnrArea,BsmtFinSF1,BsmtFinSF2,...,SaleType_ConLw,SaleType_New,SaleType_Oth,SaleType_WD,SaleCondition_Abnorml,SaleCondition_AdjLand,SaleCondition_Alloca,SaleCondition_Family,SaleCondition_Normal,SaleCondition_Partial
Id,,,,,,,,,,,,,,,,,,,,,
1461,20,80.0,11622,5,6,1961,1961,0.0,468.0,144.0,...,False,False,False,True,False,False,False,False,True,False
1462,20,81.0,14267,6,6,1958,1958,108.0,923.0,0.0,...,False,False,False,True,False,False,False,False,True,False
1463,60,74.0,13830,5,5,1997,1998,0.0,791.0,0.0,...,False,False,False,True,False,False,False,False,True,False
1464,60,78.0,9978,6,6,1998,1998,20.0,602.0,0.0,...,False,False,False,True,False,False,False,False,True,False
1465,120,43.0,5005,8,5,1992,1992,0.0,263.0,0.0,...,False,False,False,True,False,False,False,False,True,False


In [7]:
from sklearn.metrics import mean_absolute_error
from xgboost import XGBRegressor

# Define and fit the model
model_1 = XGBRegressor(random_state=0)
model_1.fit(X_train, y_train)

# Predict X_valid
pred_valid_1 = model_1.predict(X_valid)

# Calculate MAE
mae_1 = mean_absolute_error(y_valid, pred_valid_1)
print(f"Mean Absolute Error: {mae_1}")

Mean Absolute Error: 18161.826171875


In [8]:
### Refine and fit the model
model_2 = XGBRegressor(n_estimators=1000,
                       early_stopping_rounds=5,
                       learning_rate=0.05,
                       random_state=0)
model_2.fit(X_train, y_train,
            eval_set=[(X_valid, y_valid)],
            verbose=False)

# Get predictions
pred_valid_2 = model_2.predict(X_valid)

# Calculate MAE
mae_2 = mean_absolute_error(y_valid, pred_valid_2) # Your code here
print(f"Mean Absolute Error: {mae_2}")

Mean Absolute Error: 17032.76953125


In [9]:
# Break the model
model_3 = XGBRegressor(n_estimators=1,
                       random_state=0)
model_3.fit(X_train, y_train)

# Get predictions
pred_valid_3 = model_3.predict(X_valid)

# Calculate MAE
mae_3 = mean_absolute_error(y_valid, pred_valid_3)

# Uncomment to print MAE
print(f"Mean Absolute Error: {mae_3}")

Mean Absolute Error: 18298.11328125


In [12]:
# Get predictions for X_test
y_test = model_2.predict(X_test)

# Save test predictions to file
output = pd.DataFrame({'Id': X_test.index, 'SalePrice': y_test})
#output.to_csv('submission.csv', index=False)


In [13]:
from IPython.display import display, HTML

report = f"""
<div style="display: flex;">
    <div style="border-right: #fcfcfc 1px solid;">
        {X_test.to_html(index=False)}
    </div>
    <div style="background-color: #f0f6fe;">
        {output.drop(['Id'], axis=1).to_html(index=False)}
    </div>
</div>

.
"""

display(HTML(report))

MSSubClass,LotFrontage,LotArea,OverallQual,OverallCond,YearBuilt,YearRemodAdd,MasVnrArea,BsmtFinSF1,BsmtFinSF2,BsmtUnfSF,TotalBsmtSF,1stFlrSF,2ndFlrSF,LowQualFinSF,GrLivArea,BsmtFullBath,BsmtHalfBath,FullBath,HalfBath,BedroomAbvGr,KitchenAbvGr,TotRmsAbvGrd,Fireplaces,GarageYrBlt,GarageCars,GarageArea,WoodDeckSF,OpenPorchSF,EnclosedPorch,3SsnPorch,ScreenPorch,PoolArea,MiscVal,MoSold,YrSold,MSZoning_C (all),MSZoning_FV,MSZoning_RH,MSZoning_RL,MSZoning_RM,Street_Grvl,Street_Pave,Alley_Grvl,Alley_Pave,LotShape_IR1,LotShape_IR2,LotShape_IR3,LotShape_Reg,LandContour_Bnk,LandContour_HLS,LandContour_Low,LandContour_Lvl,Utilities_AllPub,Utilities_NoSeWa,LotConfig_Corner,LotConfig_CulDSac,LotConfig_FR2,LotConfig_FR3,LotConfig_Inside,LandSlope_Gtl,LandSlope_Mod,LandSlope_Sev,Condition1_Artery,Condition1_Feedr,Condition1_Norm,Condition1_PosA,Condition1_PosN,Condition1_RRAe,Condition1_RRAn,Condition1_RRNe,Condition1_RRNn,Condition2_Artery,Condition2_Feedr,Condition2_Norm,Condition2_PosA,Condition2_PosN,Condition2_RRAe,BldgType_1Fam,BldgType_2fmCon,BldgType_Duplex,BldgType_Twnhs,BldgType_TwnhsE,HouseStyle_1.5Fin,HouseStyle_1.5Unf,HouseStyle_1Story,HouseStyle_2.5Fin,HouseStyle_2.5Unf,HouseStyle_2Story,HouseStyle_SFoyer,HouseStyle_SLvl,RoofStyle_Flat,RoofStyle_Gable,RoofStyle_Gambrel,RoofStyle_Hip,RoofStyle_Mansard,RoofStyle_Shed,RoofMatl_CompShg,RoofMatl_Membran,RoofMatl_Metal,RoofMatl_Roll,RoofMatl_Tar&Grv,RoofMatl_WdShake,RoofMatl_WdShngl,MasVnrType_BrkCmn,MasVnrType_BrkFace,MasVnrType_Stone,ExterQual_Ex,ExterQual_Fa,ExterQual_Gd,ExterQual_TA,ExterCond_Ex,ExterCond_Fa,ExterCond_Gd,ExterCond_Po,ExterCond_TA,Foundation_BrkTil,Foundation_CBlock,Foundation_PConc,Foundation_Slab,Foundation_Stone,Foundation_Wood,BsmtQual_Ex,BsmtQual_Fa,BsmtQual_Gd,BsmtQual_TA,BsmtCond_Fa,BsmtCond_Gd,BsmtCond_Po,BsmtCond_TA,BsmtExposure_Av,BsmtExposure_Gd,BsmtExposure_Mn,BsmtExposure_No,BsmtFinType1_ALQ,BsmtFinType1_BLQ,BsmtFinType1_GLQ,BsmtFinType1_LwQ,BsmtFinType1_Rec,BsmtFinType1_Unf,BsmtFinType2_ALQ,BsmtFinType2_BLQ,BsmtFinType2_GLQ,BsmtFinType2_LwQ,BsmtFinType2_Rec,BsmtFinType2_Unf,Heating_Floor,Heating_GasA,Heating_GasW,Heating_Grav,Heating_OthW,Heating_Wall,HeatingQC_Ex,HeatingQC_Fa,HeatingQC_Gd,HeatingQC_Po,HeatingQC_TA,CentralAir_N,CentralAir_Y,Electrical_FuseA,Electrical_FuseF,Electrical_FuseP,Electrical_Mix,Electrical_SBrkr,KitchenQual_Ex,KitchenQual_Fa,KitchenQual_Gd,KitchenQual_TA,Functional_Maj1,Functional_Maj2,Functional_Min1,Functional_Min2,Functional_Mod,Functional_Typ,FireplaceQu_Ex,FireplaceQu_Fa,FireplaceQu_Gd,FireplaceQu_Po,FireplaceQu_TA,GarageType_2Types,GarageType_Attchd,GarageType_Basment,GarageType_BuiltIn,GarageType_CarPort,GarageType_Detchd,GarageFinish_Fin,GarageFinish_RFn,GarageFinish_Unf,GarageQual_Ex,GarageQual_Fa,GarageQual_Gd,GarageQual_Po,GarageQual_TA,GarageCond_Ex,GarageCond_Fa,GarageCond_Gd,GarageCond_Po,GarageCond_TA,PavedDrive_N,PavedDrive_P,PavedDrive_Y,PoolQC_Ex,PoolQC_Fa,PoolQC_Gd,Fence_GdPrv,Fence_GdWo,Fence_MnPrv,Fence_MnWw,MiscFeature_Gar2,MiscFeature_Othr,MiscFeature_Shed,SaleType_COD,SaleType_CWD,SaleType_Con,SaleType_ConLD,SaleType_ConLI,SaleType_ConLw,SaleType_New,SaleType_Oth,SaleType_WD,SaleCondition_Abnorml,SaleCondition_AdjLand,SaleCondition_Alloca,SaleCondition_Family,SaleCondition_Normal,SaleCondition_Partial
20,80.0,11622,5,6,1961,1961,0.0,468.0,144.0,270.0,882.0,896,0,0,896,0.0,0.0,1,0,2,1,5,0,1961.0,1.0,730.0,140,0,0,0,120,0,0,6,2010,False,False,True,False,False,False,True,False,False,False,False,False,True,False,False,False,True,True,NaN,False,False,False,False,True,True,False,False,False,True,False,False,False,False,False,False,False,False,False,True,False,False,NaN,True,False,False,False,False,False,False,True,NaN,False,False,False,False,False,True,False,False,False,False,True,NaN,NaN,NaN,False,False,False,False,False,False,False,False,False,True,False,False,False,False,True,False,True,False,False,False,False,False,False,False,True,False,False,False,True,False,False,False,True,False,False,False,False,T